# Learned Stage-Wise Curvature Tuning on PathMNIST

This notebook evaluates Learned Stage-Wise Curvature Tuning (SW-CT) on the PathMNIST dataset using an ImageNet-pretrained ResNet-18.

PathMNIST is a medical image-classification dataset containing histopathology images. Its visual characteristics differ substantially from the natural images used for ImageNet pretraining, providing a useful domain-shift experiment for evaluating Learned SW-CT.

The experiments compare four conditions:

1. **Baseline** — the original pretrained ResNet with ReLU activations and a trained downstream classifier.
2. **Single-Parameter Curvature Tuning (S-CT)** — one global beta selected through validation-based exhaustive search.
3. **Learned SW-CT with fixed initialization** — four trainable stage-wise beta parameters initialized at 0.78.
4. **Learned SW-CT with random initialization** — four trainable stage-wise beta parameters independently initialized between 0.70 and 0.99.

Each condition is evaluated using seeds 42, 43, and 44.

Experiments are conducted for both 20 and 30 epochs to determine whether additional optimization improves performance or changes the learned stage-wise beta values.

Wall-clock execution time is recorded to compare the computational cost of Baseline, S-CT, and Learned SW-CT.

In [1]:
!nvidia-smi

Fri Oct  2 09:04:06 2026       
+-----------------------------------------------------------------------------------------+
| NVIDIA-SMI 610.57.04              KMD Version: 610.57.04     CUDA UMD Version: 13.3     |
+-----------------------------------------+------------------------+----------------------+
| GPU  Name                 Persistence-M | Bus-Id          Disp.A | Volatile Uncorr. ECC |
| Fan  Temp   Perf          Pwr:Usage/Cap |           Memory-Usage | GPU-Util  Compute M. |
|                                         |                        |               MIG M. |
|=========================================+========================+======================|


|   0  Tesla T4                       On  |   00000000:F5:00.0 Off |                    0 |
| N/A   27C    P8              9W /   70W |       4MiB /  15360MiB |      0%      Default |
|                                         |                        |                  N/A |
+-----------------------------------------+------------------------+----------------------+

+-----------------------------------------------------------------------------------------+
| Processes:                                                                              |
|  GPU   GI   CI              PID   Type   Process name                        GPU Memory |
|        ID   ID                                                               Usage      |
|=========================================================================================|
|  No running processes found                                                             |
+------------------------------------------------------------------------------

In [1]:
%cd /content

!git clone -b main \
    https://github.com/NiftySnek173/research-curvature-tuning.git

%cd /content/research-curvature-tuning/src/curvature-tuning

!git branch --show-current
!git log -1 --oneline

/__modal/volumes/vo-3SJyt3mwKRdcwXqZ8WQ2xR
fatal: destination path 'curvature-tuning-research' already exists and is not an empty directory.
/__modal/volumes/vo-3SJyt3mwKRdcwXqZ8WQ2xR/curvature-tuning-research/src/curvature-tuning
stage-wise-ct
068c466 (HEAD -> stage-wise-ct, origin/stage-wise-ct, origin/HEAD) Updated aircraft with complete results


## Environment Setup

The repository dependencies are installed before running the experiments.

After installation, the Colab runtime should be restarted so that the required package versions are loaded correctly.

In [2]:
%pip install -q -r requirements.txt
%pip install --force-reinstall --no-cache-dir "numpy==1.26.3"

  DEPRECATION: Building 'autoattack' using the legacy setup.py bdist_wheel mechanism, which will be removed in a future version. pip 25.3 will enforce this behaviour change. A possible replacement is to use the standardized build interface by setting the `--use-pep517` option, (possibly combined with `--no-build-isolation`), or adding a `pyproject.toml` file to the source tree of 'autoattack'. Discussion can be found at https://github.com/pypa/pip/issues/6334
ERROR: pip's dependency resolver does not currently take into account all the packages that are installed. This behaviour is the source of the following dependency conflicts.
opencv-python-headless 5.0.0.93 requires numpy>=2; python_version >= "3.9", but you have numpy 1.26.3 which is incompatible.

[notice] A new release of pip is available: 25.2 -> 26.2.1
[notice] To update, run: pip install --upgrade pip
Note: you may need to restart the kernel to use updated packages.
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 18.3/18.3 MB 13

In [1]:
%cd /content/research-curvature-tuning/src/curvature-tuning

import os
import torch

os.environ["WANDB_MODE"] = "disabled"

print("Working directory:", os.getcwd())
print("PyTorch:", torch.__version__)
print("CUDA available:", torch.cuda.is_available())

if torch.cuda.is_available():
    print("GPU:", torch.cuda.get_device_name(0))

/content/curvature-tuning-research/src/curvature-tuning
Working directory: /content/curvature-tuning-research/src/curvature-tuning
PyTorch: 2.11.0+cu128
CUDA available: True
GPU: Tesla T4


## PathMNIST Dataset

Before running the experiments, the PathMNIST data loaders are checked to confirm that the downstream dataset can be loaded correctly.

The same dataset split and random seed protocol are used for Baseline, S-CT, and Learned SW-CT so that the methods are compared under the same conditions.

In [2]:
from utils.data import get_data_loaders

train_loader, test_loader, val_loader = get_data_loaders(
    "imagenet_to_medmnist/pathmnist",
    train_batch_size=32,
    test_batch_size=128,
    seed=42,
)

print("Train samples:", len(train_loader.dataset))
print("Validation samples:", len(val_loader.dataset))
print("Test samples:", len(test_loader.dataset))

images, labels = next(iter(train_loader))

print("Image batch shape:", images.shape)
print("Label batch shape:", labels.shape)
print("Labels:", labels[:10])

README.md:   0%|          | 0.00/7.32k [00:00<?, ?B/s]

medmnist.py:   0%|          | 0.00/4.84k [00:00<?, ?B/s]

Generating train split: 0 examples [00:00, ? examples/s]

Generating test split: 0 examples [00:00, ? examples/s]

Generating validation split: 0 examples [00:00, ? examples/s]

Train samples: 89996
Validation samples: 10004
Test samples: 7180
Image batch shape: torch.Size([32, 3, 224, 224])
Label batch shape: torch.Size([32])
Labels: tensor([2, 1, 3, 7, 5, 0, 0, 3, 5, 0])


# ResNet-18 Experiments

ResNet-18 is evaluated first because it was used during the initial development of Learned SW-CT.

The experiment compares Baseline, S-CT, fixed-initialization SW-CT, and random-initialization SW-CT.

All methods use the same ImageNet-pretrained backbone, Arabic Digits dataset split, experimental seeds, and downstream training protocol.

## ResNet-18 — 20-Epoch Evaluation

The first evaluation uses 20 training epochs.

This provides the primary reference experiment and maintains compatibility with the earlier Learned SW-CT work.

### Methods

**Baseline**

The pretrained ResNet-18 retains its original ReLU activations. The backbone is frozen and only the downstream classifier is trained.

**S-CT**

The original Single-Parameter Curvature Tuning method searches over a single beta shared throughout the network. Candidate beta values from 0.70 to 1.00 are evaluated using validation performance, and the best candidate is evaluated on the test set.

The recorded S-CT execution time includes the complete beta search rather than only the final selected beta.

**Learned SW-CT — Fixed Initialization**

Four trainable beta parameters are assigned to the four ResNet stages. All four begin at beta = 0.78.

This preserves the initialization used in the original Learned SW-CT experiments.

**Learned SW-CT — Random Initialization**

Four trainable stage-wise beta parameters are initialized independently between 0.70 and 0.99.

The random initialization is generated deterministically from the experiment seed. This allows the experiment to test whether Learned SW-CT depends on the fixed 0.78 starting value while remaining reproducible.

In [ ]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 42 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-02 01:09:26.027 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-pathmnist_resnet18_seed42_epochs20.log
2026-10-02 01:09:26.030 | INFO     | __main__:main:78 - Running on cuda
2026-10-02 01:09:29.177 | INFO     | __main__:main:105 - Testing baseline...
2026-10-02 01:09:29.194 | INFO     | __main__:main:116 - Number of trainable parameters: 4617
2026-10-02 01:09:29.194 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-02 01:13:00.667 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.112463, Accuracy: 21.88%
2026-10-02 01:13:01.008 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.214332, Accuracy: 14.82%
2026-10-02 01:13:01.360 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 2.123910, Accuracy: 20.76%
2026-10-02 01:13:01.715 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 2.009215, Accuracy: 28.59%
2026-10-02 01:13:02.075 | INFO     | train:train_epoch:47 - Epoch 1, Step

In [3]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 43 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-02 09:07:20.023 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-pathmnist_resnet18_seed43_epochs20.log
2026-10-02 09:07:20.028 | INFO     | __main__:main:78 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet18-f37072fd.pth" to /root/.cache/torch/hub/checkpoints/resnet18-f37072fd.pth
100%|███████████████████████████████████████| 44.7M/44.7M [00:00<00:00, 135MB/s]
2026-10-02 09:07:24.005 | INFO     | __main__:main:105 - Testing baseline...
2026-10-02 09:07:24.023 | INFO     | __main__:main:116 - Number of trainable parameters: 4617
2026-10-02 09:07:24.024 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-02 09:09:11.385 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.241285, Accuracy: 12.50%
2026-10-02 09:09:12.224 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.185160, Accuracy: 15.90%
2026-10-02 09:09:12.445 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss

In [4]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 44 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-02 12:01:23.602 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-pathmnist_resnet18_seed44_epochs20.log
2026-10-02 12:01:23.609 | INFO     | __main__:main:78 - Running on cuda
2026-10-02 12:01:26.779 | INFO     | __main__:main:105 - Testing baseline...
2026-10-02 12:01:26.794 | INFO     | __main__:main:116 - Number of trainable parameters: 4617
2026-10-02 12:01:26.795 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-02 12:03:18.383 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.432337, Accuracy: 9.38%
2026-10-02 12:03:19.450 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.461683, Accuracy: 8.14%
2026-10-02 12:03:19.719 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 2.332247, Accuracy: 12.41%
2026-10-02 12:03:20.024 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 2.190237, Accuracy: 20.72%
2026-10-02 12:03:20.327 | INFO     | train:train_epoch:47 - Epoch 1, Step 4

### Learned SW-CT with Fixed Beta Initialization

The original Learned SW-CT configuration is first reproduced using the fixed initialization:

\[[\beta_1,\beta_2,\beta_3,\beta_4]=[0.78,0.78,0.78,0.78].\]

The initial value is only a starting point. During training, the four beta parameters are optimized independently together with the downstream classifier.

These runs provide the reference against which random initialization will be compared.

In [5]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-02 14:59:25.406 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet18_seed42_epochs20_initfixed0.78_betalr0.01.log
2026-10-02 14:59:25.479 | INFO     | __main__:main:302 - Running on cuda
2026-10-02 14:59:28.978 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-02 14:59:28.979 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-02 14:59:29.058 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-02 14:59:29.059 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-02 14:59:29.059 | INFO     | __main__:main:439 - Total trainable parameters: 4621
2026-10-02 14:59:30.555 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.455714, Accuracy: 12.50%
2026-10-02 14:59:44.938 | INFO     | train:train_

In [6]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-02 17:20:38.076 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet18_seed43_epochs20_initfixed0.78_betalr0.01.log
2026-10-02 17:20:38.147 | INFO     | __main__:main:302 - Running on cuda
2026-10-02 17:20:41.408 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-02 17:20:41.409 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-02 17:20:41.493 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-02 17:20:41.494 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-02 17:20:41.494 | INFO     | __main__:main:439 - Total trainable parameters: 4621
2026-10-02 17:20:42.838 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.618068, Accuracy: 12.50%
2026-10-02 17:20:57.122 | INFO     | train:train_

In [7]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-02 19:42:26.229 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet18_seed44_epochs20_initfixed0.78_betalr0.01.log
2026-10-02 19:42:26.330 | INFO     | __main__:main:302 - Running on cuda
2026-10-02 19:42:29.487 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-02 19:42:29.488 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-02 19:42:29.591 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-02 19:42:29.592 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-02 19:42:29.593 | INFO     | __main__:main:439 - Total trainable parameters: 4621
2026-10-02 19:42:31.259 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.507685, Accuracy: 9.38%
2026-10-02 19:42:45.757 | INFO     | train:train_e

### Learned SW-CT with Random Beta Initialization

The fixed beta = 0.78 initialization may raise the question of whether Learned SW-CT performs well only because its starting point was informed by the earlier S-CT experiments.

To test this dependency, each of the four stage-wise beta parameters is now initialized independently from a uniform distribution between 0.70 and 0.99.

The initialization is reproducible: the random generator is seeded using the experiment seed. Therefore, each seed always receives the same initial beta vector.

If random initialization produces similar performance to the fixed 0.78 experiment, this provides evidence that the Learned SW-CT result is not dependent on a single hand-selected initialization.

In [8]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-02 22:06:09.471 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet18_seed42_epochs20_initrandom_betalr0.01.log
2026-10-02 22:06:09.563 | INFO     | __main__:main:302 - Running on cuda
2026-10-02 22:06:12.954 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-02 22:06:12.957 | INFO     | __main__:main:394 - Requested initial stage betas: [0.924447, 0.827275, 0.948993, 0.902237]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-02 22:06:13.020 | INFO     | __main__:main:418 - Initial stage betas: [0.924447238445282, 0.827274739742279, 0.9489933848381042, 0.9022367000579834]
2026-10-02 22:06:13.021 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-02 22:06:13.022 | INFO     | __main__:main:439 - Total trainable parameters: 4621
2026-10-02 22:06:14.749 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.384657, Accuracy: 15.62%
2026-10-02 22:06:29.414 | INFO     | 

In [9]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-03 00:29:43.820 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet18_seed43_epochs20_initrandom_betalr0.01.log
2026-10-03 00:29:43.897 | INFO     | __main__:main:302 - Running on cuda
2026-10-03 00:29:47.014 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-03 00:29:47.015 | INFO     | __main__:main:394 - Requested initial stage betas: [0.889167, 0.712695, 0.705809, 0.943372]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-03 00:29:47.120 | INFO     | __main__:main:418 - Initial stage betas: [0.8891667127609253, 0.7126947641372681, 0.7058085799217224, 0.9433716535568237]
2026-10-03 00:29:47.121 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-03 00:29:47.121 | INFO     | __main__:main:439 - Total trainable parameters: 4621
2026-10-03 00:29:48.543 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.618388, Accuracy: 6.25%
2026-10-03 00:30:03.099 | INFO     |

In [10]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-03 02:51:06.692 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet18_seed44_epochs20_initrandom_betalr0.01.log
2026-10-03 02:51:07.057 | INFO     | __main__:main:302 - Running on cuda
2026-10-03 02:51:10.199 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-03 02:51:10.200 | INFO     | __main__:main:394 - Requested initial stage betas: [0.735544, 0.774853, 0.817674, 0.981063]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-03 02:51:10.288 | INFO     | __main__:main:418 - Initial stage betas: [0.7355440258979797, 0.7748528122901917, 0.8176735043525696, 0.9810633659362793]
2026-10-03 02:51:10.290 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-03 02:51:10.291 | INFO     | __main__:main:439 - Total trainable parameters: 4621
2026-10-03 02:51:11.830 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.469105, Accuracy: 0.00%
2026-10-03 02:51:26.299 | INFO     |

# ResNet-18 — 30-Epoch Evaluation

The same experiments are now repeated for 30 epochs.

The purpose of increasing the training budget is to determine whether the 20-epoch results are limited by insufficient optimization.

If a method improves substantially with 30 epochs, this suggests that additional optimization is useful. If performance remains similar, it indicates that the method has largely stabilized within the original 20-epoch training budget.

All other experimental settings remain unchanged.

For random-initialization SW-CT, the same seed produces exactly the same initial four-beta vector in both the 20-epoch and 30-epoch experiments. Therefore, initialization is held constant while the training duration changes.

Execution time is again recorded to measure the computational cost of extending training from 20 to 30 epochs.

In [3]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 42 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-03 08:40:22.356 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-pathmnist_resnet18_seed42_epochs30.log
2026-10-03 08:40:22.361 | INFO     | __main__:main:78 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet18-f37072fd.pth" to /root/.cache/torch/hub/checkpoints/resnet18-f37072fd.pth
100%|███████████████████████████████████████| 44.7M/44.7M [00:00<00:00, 108MB/s]
2026-10-03 08:40:26.821 | INFO     | __main__:main:105 - Testing baseline...
2026-10-03 08:40:26.835 | INFO     | __main__:main:116 - Number of trainable parameters: 4617
2026-10-03 08:40:26.836 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-03 08:42:18.245 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.112463, Accuracy: 21.88%
2026-10-03 08:42:18.930 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.214332, Accuracy: 14.82%
2026-10-03 08:42:19.384 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss

In [4]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 43 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-03 12:39:11.118 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-pathmnist_resnet18_seed43_epochs30.log
2026-10-03 12:39:11.123 | INFO     | __main__:main:78 - Running on cuda
2026-10-03 12:39:14.841 | INFO     | __main__:main:105 - Testing baseline...
2026-10-03 12:39:14.856 | INFO     | __main__:main:116 - Number of trainable parameters: 4617
2026-10-03 12:39:14.857 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-03 12:41:05.821 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.241285, Accuracy: 12.50%
2026-10-03 12:41:06.568 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.185160, Accuracy: 15.90%
2026-10-03 12:41:07.132 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 2.081405, Accuracy: 22.48%
2026-10-03 12:41:07.350 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.965867, Accuracy: 30.73%
2026-10-03 12:41:07.574 | INFO     | train:train_epoch:47 - Epoch 1, Step

In [5]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 44 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-03 16:12:01.389 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-pathmnist_resnet18_seed44_epochs30.log
2026-10-03 16:12:01.395 | INFO     | __main__:main:78 - Running on cuda
2026-10-03 16:12:05.300 | INFO     | __main__:main:105 - Testing baseline...
2026-10-03 16:12:05.320 | INFO     | __main__:main:116 - Number of trainable parameters: 4617
2026-10-03 16:12:05.321 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-03 16:13:53.818 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.432337, Accuracy: 9.38%
2026-10-03 16:13:54.464 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.461683, Accuracy: 8.14%
2026-10-03 16:13:54.948 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 2.332247, Accuracy: 12.41%
2026-10-03 16:13:55.224 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 2.190237, Accuracy: 20.72%
2026-10-03 16:13:55.476 | INFO     | train:train_epoch:47 - Epoch 1, Step 4

In [6]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-03 19:42:07.410 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet18_seed42_epochs30_initfixed0.78_betalr0.01.log
2026-10-03 19:42:07.506 | INFO     | __main__:main:302 - Running on cuda
2026-10-03 19:42:11.404 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-03 19:42:11.405 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-03 19:42:11.455 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-03 19:42:11.456 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-03 19:42:11.456 | INFO     | __main__:main:439 - Total trainable parameters: 4621
2026-10-03 19:42:12.935 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.455714, Accuracy: 12.50%
2026-10-03 19:42:27.263 | INFO     | train:train_

In [7]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-03 23:15:48.843 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet18_seed43_epochs30_initfixed0.78_betalr0.01.log
2026-10-03 23:15:48.921 | INFO     | __main__:main:302 - Running on cuda
2026-10-03 23:15:52.612 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-03 23:15:52.613 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-03 23:15:52.701 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-03 23:15:52.702 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-03 23:15:52.702 | INFO     | __main__:main:439 - Total trainable parameters: 4621
2026-10-03 23:15:54.619 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.618068, Accuracy: 12.50%
2026-10-03 23:16:08.956 | INFO     | train:train_

In [3]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-04 12:13:48.382 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet18_seed44_epochs30_initfixed0.78_betalr0.01.log
2026-10-04 12:13:48.446 | INFO     | __main__:main:302 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet18-f37072fd.pth" to /root/.cache/torch/hub/checkpoints/resnet18-f37072fd.pth
100%|███████████████████████████████████████| 44.7M/44.7M [00:00<00:00, 157MB/s]
2026-10-04 12:13:50.683 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-04 12:13:50.683 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-04 12:13:50.714 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-04 12:13:50.715 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-04 12:13:50.715 | INFO     

In [4]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-04 16:09:44.466 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet18_seed42_epochs30_initrandom_betalr0.01.log
2026-10-04 16:09:44.531 | INFO     | __main__:main:302 - Running on cuda
2026-10-04 16:09:46.608 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-04 16:09:46.608 | INFO     | __main__:main:394 - Requested initial stage betas: [0.924447, 0.827275, 0.948993, 0.902237]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-04 16:09:46.641 | INFO     | __main__:main:418 - Initial stage betas: [0.924447238445282, 0.827274739742279, 0.9489933848381042, 0.9022367000579834]
2026-10-04 16:09:46.641 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-04 16:09:46.641 | INFO     | __main__:main:439 - Total trainable parameters: 4621
2026-10-04 16:09:47.592 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.384657, Accuracy: 15.62%
2026-10-04 16:10:03.392 | INFO     | 

In [3]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-05 00:10:43.623 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet18_seed43_epochs30_initrandom_betalr0.01.log
2026-10-05 00:10:43.720 | INFO     | __main__:main:302 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet18-f37072fd.pth" to /root/.cache/torch/hub/checkpoints/resnet18-f37072fd.pth
100%|███████████████████████████████████████| 44.7M/44.7M [00:00<00:00, 179MB/s]
2026-10-05 00:10:45.952 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-05 00:10:45.952 | INFO     | __main__:main:394 - Requested initial stage betas: [0.889167, 0.712695, 0.705809, 0.943372]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-05 00:10:45.982 | INFO     | __main__:main:418 - Initial stage betas: [0.8891667127609253, 0.7126947641372681, 0.7058085799217224, 0.9433716535568237]
2026-10-05 00:10:45.983 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-05 00:10:45.9

In [4]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet18 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-05 03:58:35.462 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet18_seed44_epochs30_initrandom_betalr0.01.log
2026-10-05 03:58:35.523 | INFO     | __main__:main:302 - Running on cuda
2026-10-05 03:58:37.250 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-05 03:58:37.251 | INFO     | __main__:main:394 - Requested initial stage betas: [0.735544, 0.774853, 0.817674, 0.981063]
Stage-Wise CT ReLU counts: [3, 2, 2, 2]
2026-10-05 03:58:37.287 | INFO     | __main__:main:418 - Initial stage betas: [0.7355440258979797, 0.7748528122901917, 0.8176735043525696, 0.9810633659362793]
2026-10-05 03:58:37.288 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-05 03:58:37.288 | INFO     | __main__:main:439 - Total trainable parameters: 4621
2026-10-05 03:58:38.250 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.469105, Accuracy: 0.00%
2026-10-05 03:58:53.606 | INFO     |